In [0]:
spark.conf.set(
  "fs.azure.account.key.<storage-account-name>.dfs.core.windows.net",
  "<access-key>"
)

In [0]:
# Read raw Parquet data from ADLS (ADLS Gen2 - abfss protocol)
parquet_path = "abfss://<adls-container-name>@<adls-storage-account-name>.dfs.core.windows.net/silver"

In [0]:
# Load the dataset from Parquet stored in ADLS

gold_df = spark.read.option("header", True).parquet(parquet_path)

In [0]:
gold_df.printSchema()

root
 |-- Summons_Number: long (nullable = true)
 |-- Plate_ID: string (nullable = true)
 |-- Registration_State: string (nullable = true)
 |-- Plate_Type: string (nullable = true)
 |-- Issue_Date: date (nullable = true)
 |-- Violation_Code: integer (nullable = true)
 |-- Vehicle_Body_Type: string (nullable = true)
 |-- Vehicle_Make: string (nullable = true)
 |-- Issuing_Agency: string (nullable = true)
 |-- Vehicle_Expiration_Date: integer (nullable = true)
 |-- Violation_Location: integer (nullable = true)
 |-- Violation_Precinct: integer (nullable = true)
 |-- Issuer_Precinct: integer (nullable = true)
 |-- Issuer_Code: integer (nullable = true)
 |-- Issuer_Command: string (nullable = true)
 |-- Issuer_Squad: string (nullable = true)
 |-- Time_First_Observed: string (nullable = true)
 |-- Violation_County: string (nullable = true)
 |-- Violation_In_Front_Of_Or_Opposite: string (nullable = true)
 |-- House_Number: string (nullable = true)
 |-- Street_Name: string (nullable = true)
 |

In [0]:
gold_df.select("Days_Parking_in_Full_Effect").display()

Days_Parking_in_Full_Effect
null
null
null
null
null
null
null
null
null
null


In [0]:
gold_df.select("Days_Parking_in_Full_Effect").distinct().show(50, truncate=False)


+--------------------------------------------------------------+
|Days_Parking_in_Full_Effect                                   |
+--------------------------------------------------------------+
|Monday, Wednesday                                             |
|Monday, Tuesday, Wednesday, Thursday, Saturday                |
|Friday, Saturday, Sunday                                      |
|Monday, Tuesday, Wednesday, Friday, Saturday, Sunday          |
|Monday, Tuesday, Wednesday, Thursday, Friday, Sunday          |
|Tuesday, Wednesday                                            |
|Thursday, Sunday                                              |
|Wednesday                                                     |
|Tuesday                                                       |
|Monday, Tuesday, Thursday, Friday, Saturday, Sunday           |
|Monday, Tuesday, Wednesday, Thursday, Sunday                  |
|null                                                          |
|Monday, Tuesday, Wednesd

In [0]:
gold_df.select("Vehicle_Body_Type").distinct().show(50, truncate=False)


+-----------------+
|Vehicle_Body_Type|
+-----------------+
|REFG             |
|UV               |
|2HB              |
|BUS              |
|SW               |
|CG               |
|4DSD             |
|null             |
|LL               |
|VAN              |
|4DSE             |
|CV               |
|SU               |
|COUP             |
|TAXI             |
|4DR              |
|PK               |
|VT               |
|4W               |
|FB               |
|PV               |
|SPOR             |
|SUBU             |
|WAGO             |
|2D               |
|PKUP             |
|WG               |
|4DOO             |
|TRAC             |
|HATC             |
|SEDN             |
|SUBN             |
|CONV             |
|FLAT             |
|SDN              |
|LIMO             |
|SD               |
|2S               |
|UK               |
|4S               |
|DELV             |
|APUR             |
|CP               |
|UTIL             |
|4D               |
|4                |
|2DSD             |


In [0]:
spark.conf.set("spark.sql.catalog.iceberg_catalog", "org.apache.iceberg.spark.SparkCatalog")
spark.conf.set("spark.sql.catalog.iceberg_catalog.type", "hadoop")
spark.conf.set("spark.sql.catalog.iceberg_catalog.warehouse", "abfss://<adls-container-name>@<adls-storage-account-name>.dfs.core.windows.net/iceberg_warehouse/")

In [0]:
spark.sql("CREATE DATABASE IF NOT EXISTS iceberg_db")

Out[6]: DataFrame[]

In [0]:
# Drop existing table if needed
spark.sql("DROP TABLE IF EXISTS iceberg_catalog.iceberg_db.parking_iceberg")

Out[7]: DataFrame[]


### Write DataFrame to Iceberg Table

In [0]:
gold_df.writeTo("iceberg_catalog.iceberg_db.parking_iceberg").createOrReplace()

In [0]:
%sql

Select * from iceberg_catalog.iceberg_db.parking_iceberg;

Summons_Number,Plate_ID,Registration_State,Plate_Type,Issue_Date,Violation_Code,Vehicle_Body_Type,Vehicle_Make,Issuing_Agency,Vehicle_Expiration_Date,Violation_Location,Violation_Precinct,Issuer_Precinct,Issuer_Code,Issuer_Command,Issuer_Squad,Time_First_Observed,Violation_County,Violation_In_Front_Of_Or_Opposite,House_Number,Street_Name,Intersecting_Street,Law_Section,Sub_Division,Violation_Legal_Code,Days_Parking_In_Effect,From_Hours_In_Effect,To_Hours_In_Effect,Vehicle_Color,Unregistered_Vehicle,Vehicle_Year,Meter_Number,Feet_From_Curb,Violation_Post_Code,Violation_Description,Parking_Violation_Time,Days_Parking_in_Full_Effect
4881563609,LEX2411,New York,Passenger,2024-01-15,36,SUBN,NISSAN,V,0,null,0,0,0,null,null,null,Queens,null,null,WB 73RD AVE @ 164TH,ST,1180,B,T,null,null,null,RD,null,2011,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:20 AM,null
4881563610,GXU5495,New York,Passenger,2024-01-15,36,SUBN,TOYOTA,V,0,null,0,0,0,null,null,null,Queens,null,null,SB WOODHAVEN BLVD @,88TH AVE,1180,B,T,null,null,null,GY,null,2012,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:20 AM,null
4881563622,HTZ1273,New York,Passenger,2024-01-15,36,4DSD,INFINITI,V,0,null,0,0,0,null,null,null,Queens,null,null,EB S CONDUIT AVE @ 7,9TH ST,1180,B,T,null,null,null,GY,null,2007,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:20 AM,null
4881563634,KZE9291,New York,Passenger,2024-01-15,36,SUBN,HONDA,V,0,null,0,0,0,null,null,null,Queens,null,null,WB QUEENS BLVD @ 72N,D RD,1180,B,T,null,null,null,WH,null,2021,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:20 AM,null
4881563646,KNV6399,New York,Passenger,2024-01-15,36,PICK,RAM,V,0,null,0,0,0,null,null,null,Queens,null,null,SB 188TH ST @ CAMBRI,DGE RD,1180,B,T,null,null,null,GY,null,2018,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563658,KWN5089,New York,Passenger,2024-01-15,36,SUBN,DODGE,V,0,null,0,0,0,null,null,null,Queens,null,null,NB SPRINGFIELD BLVD,@ 109TH AVE,1180,B,T,null,null,null,GY,null,2011,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563660,KSU5799,New York,Passenger,2024-01-15,36,SUBN,SUBARU,V,0,null,0,0,0,null,null,null,Manhattan,null,null,EB E HOUSTON ST @ AV,E C,1180,B,T,null,null,null,WH,null,2016,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563671,KYE8479,New York,Passenger,2024-01-15,36,SUBN,FORD,V,0,null,0,0,0,null,null,null,Queens,null,null,WB N CONDUIT AVE @ 8,8TH ST,1180,B,T,null,null,null,BK,null,2001,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563683,X77RJL,New Jersey,Passenger,2024-01-15,36,SPOR,HONDA,V,0,null,0,0,0,null,null,null,Manhattan,null,null,SB WEST ST @ LEROY S,T,1180,B,T,null,null,null,null,null,2022,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563695,MHF4561,Pennsylvania,Passenger,2024-01-15,36,SDN,MERCU,V,0,null,0,0,0,null,null,null,Queens,null,null,EB LINDEN BLVD @ O'D,ONNELL RD,1180,B,T,null,null,null,null,null,2005,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null


In [0]:
%sql

Select * from iceberg_catalog.iceberg_db.parking_iceberg limit 10;

Summons_Number,Plate_ID,Registration_State,Plate_Type,Issue_Date,Violation_Code,Vehicle_Body_Type,Vehicle_Make,Issuing_Agency,Vehicle_Expiration_Date,Violation_Location,Violation_Precinct,Issuer_Precinct,Issuer_Code,Issuer_Command,Issuer_Squad,Time_First_Observed,Violation_County,Violation_In_Front_Of_Or_Opposite,House_Number,Street_Name,Intersecting_Street,Law_Section,Sub_Division,Violation_Legal_Code,Days_Parking_In_Effect,From_Hours_In_Effect,To_Hours_In_Effect,Vehicle_Color,Unregistered_Vehicle,Vehicle_Year,Meter_Number,Feet_From_Curb,Violation_Post_Code,Violation_Description,Parking_Violation_Time,Days_Parking_in_Full_Effect
4881563609,LEX2411,New York,Passenger,2024-01-15,36,SUBN,NISSAN,V,0,null,0,0,0,null,null,null,Queens,null,null,WB 73RD AVE @ 164TH,ST,1180,B,T,null,null,null,RD,null,2011,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:20 AM,null
4881563610,GXU5495,New York,Passenger,2024-01-15,36,SUBN,TOYOTA,V,0,null,0,0,0,null,null,null,Queens,null,null,SB WOODHAVEN BLVD @,88TH AVE,1180,B,T,null,null,null,GY,null,2012,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:20 AM,null
4881563622,HTZ1273,New York,Passenger,2024-01-15,36,4DSD,INFINITI,V,0,null,0,0,0,null,null,null,Queens,null,null,EB S CONDUIT AVE @ 7,9TH ST,1180,B,T,null,null,null,GY,null,2007,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:20 AM,null
4881563634,KZE9291,New York,Passenger,2024-01-15,36,SUBN,HONDA,V,0,null,0,0,0,null,null,null,Queens,null,null,WB QUEENS BLVD @ 72N,D RD,1180,B,T,null,null,null,WH,null,2021,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:20 AM,null
4881563646,KNV6399,New York,Passenger,2024-01-15,36,PICK,RAM,V,0,null,0,0,0,null,null,null,Queens,null,null,SB 188TH ST @ CAMBRI,DGE RD,1180,B,T,null,null,null,GY,null,2018,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563658,KWN5089,New York,Passenger,2024-01-15,36,SUBN,DODGE,V,0,null,0,0,0,null,null,null,Queens,null,null,NB SPRINGFIELD BLVD,@ 109TH AVE,1180,B,T,null,null,null,GY,null,2011,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563660,KSU5799,New York,Passenger,2024-01-15,36,SUBN,SUBARU,V,0,null,0,0,0,null,null,null,Manhattan,null,null,EB E HOUSTON ST @ AV,E C,1180,B,T,null,null,null,WH,null,2016,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563671,KYE8479,New York,Passenger,2024-01-15,36,SUBN,FORD,V,0,null,0,0,0,null,null,null,Queens,null,null,WB N CONDUIT AVE @ 8,8TH ST,1180,B,T,null,null,null,BK,null,2001,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563683,X77RJL,New Jersey,Passenger,2024-01-15,36,SPOR,HONDA,V,0,null,0,0,0,null,null,null,Manhattan,null,null,SB WEST ST @ LEROY S,T,1180,B,T,null,null,null,null,null,2022,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null
4881563695,MHF4561,Pennsylvania,Passenger,2024-01-15,36,SDN,MERCU,V,0,null,0,0,0,null,null,null,Queens,null,null,EB LINDEN BLVD @ O'D,ONNELL RD,1180,B,T,null,null,null,null,null,2005,null,0,null,PHTO SCHOOL ZN SPEED VIOLATION,11:21 AM,null


In [0]:
%sql

DESCRIBE EXTENDED iceberg_catalog.iceberg_db.parking_iceberg;

col_name,data_type,comment
Summons_Number,bigint,null
Plate_ID,string,null
Registration_State,string,null
Plate_Type,string,null
Issue_Date,date,null
Violation_Code,int,null
Vehicle_Body_Type,string,null
Vehicle_Make,string,null
Issuing_Agency,string,null
Vehicle_Expiration_Date,int,null


In [0]:
%sql

Select * from iceberg_catalog.iceberg_db.parking_iceberg.metadata_log_entries;

timestamp,file,latest_snapshot_id,latest_schema_id,latest_sequence_number
2025-06-11T12:58:55.404+0000,abfss://icebergdatalakecontainer@icebergdatalakestorage.dfs.core.windows.net/iceberg_warehouse/iceberg_db/parking_iceberg/metadata/v1.metadata.json,2654289436030805151,0,1


In [0]:
%sql

SELECT * FROM iceberg_catalog.iceberg_db.parking_iceberg.snapshots;

committed_at,snapshot_id,parent_id,operation,manifest_list,summary
2025-06-11T12:58:55.404+0000,2654289436030805151,null,append,abfss://icebergdatalakecontainer@icebergdatalakestorage.dfs.core.windows.net/iceberg_warehouse/iceberg_db/parking_iceberg/metadata/snap-2654289436030805151-1-31c3b8bb-422e-4337-adca-e2d15063a54e.avro,"Map(added-records -> 29816785, total-equality-deletes -> 0, changed-partition-count -> 1, total-position-deletes -> 0, total-files-size -> 557669551, total-records -> 29816785, total-delete-files -> 0, added-data-files -> 9, total-data-files -> 9, added-files-size -> 557669551, spark.app.id -> local-1749636801941)"



### Analysis: Apache Iceberg Table


#### 1. Count total number of rows

In [0]:
%sql

Select count(*) FROM iceberg_catalog.iceberg_db.parking_iceberg;

count(1)
29816785



#### 2. Finding Distinct Vehicle Makes

In [0]:
%sql

SELECT DISTINCT Vehicle_Make FROM iceberg_catalog.iceberg_db.parking_iceberg;

Vehicle_Make
NIU
FRER
MIZ
BOX
GENGY
CAR N
FRET
LT
ROGE
SAA.



#### 3. Top 30 Registration States by Number of Vioaltion Records

In [0]:
%sql

SELECT Registration_State, COUNT(*) AS cnt
FROM iceberg_catalog.iceberg_db.parking_iceberg
GROUP BY Registration_State
ORDER BY cnt DESC
LIMIT 30;

Registration_State,cnt
New York,21624872
New Jersey,2997801
Pennsylvania,1172709
Florida,655598
Connecticut,539461
Virginia,299340
Massachusetts,260147
Georgia,239411
Indiana,211430
North Carolina,204485


#### 4. Most Common Violation Codes

In [0]:
%sql
-- Violation codes most frequently issued
SELECT 
  Violation_Code,
  COUNT(*) AS total_count
FROM iceberg_catalog.iceberg_db.parking_iceberg
GROUP BY Violation_Code
ORDER BY total_count DESC
LIMIT 10;


Violation_Code,total_count
36,9734950
21,3424206
38,2170145
14,1497193
5,1365190
7,1281857
40,1194078
20,1115797
71,1014707
70,690517


#### 5. Count of Specific Violations for Selected States and Vehicle Makes

In [0]:
%sql

SELECT COUNT(*) AS violation_count
FROM iceberg_catalog.iceberg_db.parking_iceberg
WHERE Violation_Code IN (14, 19, 40)
  AND Registration_State IN ('New York', 'New Jersey', 'South Carolina', 'Oregon', 'Nebraska')
  AND Vehicle_Make IN ('HYUNDAI', 'BMW', 'TOYOTA', 'AUDI', 'LEXUS', 'HONDA', 'VOLVO', 'SKODA');


violation_count
734463



### 6. Count Distinct Registration States, Vehicle Makes, and Vehicle Colors

In [0]:
%sql

SELECT
  COUNT(DISTINCT Registration_State) AS distinct_states,
  COUNT(DISTINCT Vehicle_Make) AS distinct_vehicle_makes,
  COUNT(DISTINCT Vehicle_Color) AS distinct_vehicle_colors
FROM iceberg_catalog.iceberg_db.parking_iceberg;

distinct_states,distinct_vehicle_makes,distinct_vehicle_colors
69,5972,1406



### 7. Average Vehicle Age by Make for Vehicles Manufactured After 2023

In [0]:
%sql

SELECT 
  Vehicle_Make, 
  AVG(YEAR(Issue_Date) - Vehicle_Year) AS avg_age
FROM iceberg_catalog.iceberg_db.parking_iceberg
WHERE Vehicle_Year <= 2023
GROUP BY Vehicle_Make
ORDER BY avg_age DESC;

Vehicle_Make,avg_age
ANHI,2027.0
COUTT,2025.0
HYADA,2025.0
QCUR,2025.0
BS,2025.0
POPRS,2025.0
LRE,2025.0
MINIO,2025.0
SBAR,2025.0
CAMMA,2025.0


####  8. Most Violated Legal Sections

In [0]:
%sql

SELECT 
  Law_Section,
  COUNT(*) AS violations
FROM iceberg_catalog.iceberg_db.parking_iceberg
WHERE Law_Section IS NOT NULL
GROUP BY Law_Section
ORDER BY violations DESC
LIMIT 10;


Law_Section,violations
408,17029229
1180,9734948
1111,3041723
0,3817
385,2922
411,2695
410,1451


#### 9. Vehicle Type vs Violation Pattern (e.g., Commercial vs Passenger)

In [0]:
%sql

SELECT 
  Vehicle_Body_Type,
  COUNT(*) AS total_violations
FROM iceberg_catalog.iceberg_db.parking_iceberg
GROUP BY Vehicle_Body_Type
ORDER BY total_violations DESC;


Vehicle_Body_Type,total_violations
SUBN,13388934
4DSD,7047381
VAN,2359444
PICK,946615
DELV,743129
SPOR,660696
SDN,475010
2DSD,471736
UT,459255
SEDA,431666


#### 10. Vehicle Make and Year vs Violations

In [0]:
%sql

SELECT 
  Vehicle_Make, 
  Vehicle_Year,
  COUNT(*) AS total_violations
FROM iceberg_catalog.iceberg_db.parking_iceberg
WHERE Vehicle_Make IS NOT NULL AND Vehicle_Year IS NOT NULL
GROUP BY Vehicle_Make, Vehicle_Year
ORDER BY total_violations DESC
LIMIT 15;


Vehicle_Make,Vehicle_Year,total_violations
HONDA,0,558404
TOYOTA,0,472100
FORD,0,458549
NISSAN,0,345640
CHEVROLET,0,266952
BMW,0,256636
TOYOTA,2021,254437
TOYOTA,2023,252613
TOYOTA,2022,250721
ME/BE,0,230684
